In [0]:
silver_df  = spark.table("bronze_cards")
display(silver_df)

Card_ID,Customer_ID,Card_Type,Card_Network,Credit_Limit,Card_Status,Contactless,Card_Mode,Issue_Date,Expiry_Date,_ingested_at,_source_file
CARD500001,CUST100001,Gold,RuPay,587317,Active,Yes,Physical,2021-04-24,2026-04-24,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500002,CUST100002,Silver,Visa,150720,Active,Yes,Virtual,2020-06-30,2025-06-30,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500003,CUST100003,Gold,RuPay,631005,Active,Yes,Physical,2022-04-04,2027-04-04,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500004,CUST100004,Silver,Mastercard,285015,Expired,Yes,Virtual,2020-07-21,2025-07-21,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500005,CUST100005,Gold,Mastercard,348591,Active,Yes,Physical,2024-07-24,2029-07-24,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500006,CUST100005,Classic,Visa,90129,Active,Yes,Physical,2019-10-08,2024-10-08,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500007,CUST100006,Silver,Visa,223797,Active,Yes,Physical,2019-05-27,2024-05-27,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500008,CUST100007,Platinum,Mastercard,764925,Active,No,Virtual,2022-05-23,2027-05-23,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500009,CUST100008,Gold,Mastercard,555357,Active,No,Virtual,2022-01-06,2027-01-06,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500010,CUST100009,Platinum,Visa,971876,Active,Yes,Physical,2026-07-17,2031-07-17,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv


In [0]:
from pyspark.sql.functions import trim,col
for c , dtype in silver_df.dtypes:
    if dtype == "string":
        silver_df = silver_df.withColumn(c,trim(col(c)))
print("whitespace trimmed")

whitespace trimmed


In [0]:
silver_df.columns

['Card_ID',
 'Customer_ID',
 'Card_Type',
 'Card_Network',
 'Credit_Limit',
 'Card_Status',
 'Contactless',
 'Card_Mode',
 'Issue_Date',
 'Expiry_Date',
 '_ingested_at',
 '_source_file']

In [0]:
rename_map = {
    "Card_ID":       "card_id",
    "Customer_ID":   "customer_id",
    "Card_Type":     "card_type",
    "Card_Network":  "card_network",
    "Credit_Limit":  "credit_limit",
    "Card_Status":   "card_status",
    "Contactless":   "contactless",
    "Card_Mode":     "card_mode",
    "Expiry_Date":   "expiry_date",
    "Issue_Date":    "issue_date",
}

for old, new in rename_map.items():
    if old in silver_df.columns:
        silver_df = silver_df.withColumnRenamed(old, new)

print("✅ Columns renamed")
print(silver_df.columns)

✅ Columns renamed
['card_id', 'customer_id', 'card_type', 'card_network', 'credit_limit', 'card_status', 'contactless', 'card_mode', 'issue_date', 'expiry_date', '_ingested_at', '_source_file']


In [0]:
silver_df.columns

['card_id',
 'customer_id',
 'card_type',
 'card_network',
 'credit_limit',
 'card_status',
 'contactless',
 'card_mode',
 'issue_date',
 'expiry_date',
 '_ingested_at',
 '_source_file']

In [0]:
before  = silver_df.count()
silver_df  = silver_df.dropDuplicates()
print(f"Dropped {before - silver_df.count()} dupes")

Dropped 0 dupes


In [0]:
silver_df = silver_df.dropna(subset=["card_id"])
print(f" Now {silver_df.count()} rows")

 Now 32457 rows


In [0]:
display(silver_df)

card_id,customer_id,card_type,card_network,credit_limit,card_status,contactless,card_mode,issue_date,expiry_date,_ingested_at,_source_file
CARD500001,CUST100001,Gold,RuPay,587317,Active,Yes,Physical,2021-04-24,2026-04-24,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500002,CUST100002,Silver,Visa,150720,Active,Yes,Virtual,2020-06-30,2025-06-30,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500003,CUST100003,Gold,RuPay,631005,Active,Yes,Physical,2022-04-04,2027-04-04,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500004,CUST100004,Silver,Mastercard,285015,Expired,Yes,Virtual,2020-07-21,2025-07-21,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500005,CUST100005,Gold,Mastercard,348591,Active,Yes,Physical,2024-07-24,2029-07-24,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500006,CUST100005,Classic,Visa,90129,Active,Yes,Physical,2019-10-08,2024-10-08,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500007,CUST100006,Silver,Visa,223797,Active,Yes,Physical,2019-05-27,2024-05-27,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500008,CUST100007,Platinum,Mastercard,764925,Active,No,Virtual,2022-05-23,2027-05-23,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500009,CUST100008,Gold,Mastercard,555357,Active,No,Virtual,2022-01-06,2027-01-06,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv
CARD500010,CUST100009,Platinum,Visa,971876,Active,Yes,Physical,2026-07-17,2031-07-17,2026-10-13T10:05:39.080Z,dbfs:/Volumes/finance-fraud-pipeline/finance_schema/bank_raw/Cards_Data.csv


In [0]:
from pyspark.sql.functions import current_timestamp
silver_df = silver_df.withColumn("_silver_updated_at", current_timestamp())
print(" Audit column added")

 Audit column added


In [0]:
silver_df.write.format("delta").mode("overwrite").saveAsTable("silver_cards")
print(f" silver_cards: {spark.table('silver_cards').count():,} rows")

 silver_cards: 32,457 rows
